In [5]:
import pandas as pd
import numpy as np
import plotly.graph_objects as go
import plotly.express as px
import scipy


In [6]:

df = pd.read_csv(r"../Prime_code/primes_with_gaps.csv")

primes = df["prime"].values
gaps = df["gap"].values


gaps = gaps[gaps > 0]

print("Total primes:", len(primes))

Total primes: 148933


In [7]:
df.head(
    
)

,prime,gap
0,2,0
1,3,1
2,5,2
3,7,2
4,11,4


# Prime number theorem
It implies that prime becomes less as X increases

In [ ]:
x = primes
pi_x = np.arange(1, len(primes)+1)
approx = x / np.log(x)


fig = go.Figure()

fig.add_trace(go.Scatter(x=x, y=pi_x, mode='lines', name='π(x)'))
fig.add_trace(go.Scatter(x=x, y=approx, mode='lines', name='x/log(x)', line=dict(dash='dash')))

fig.update_layout(title="Prime Distribution vs x/log(x)/ PNT(Prime Numebr Theorem)")

fig.show()

Skewness

In [9]:
fig = px.histogram(
    gaps,
    nbins=100,
    labels={"value": "Prime Gap", "count": "Frequency"},
    title="Prime Gap Distribution"
)
fig.show()

In [10]:
density = scipy.stats.gaussian_kde(gaps)
xs = np.linspace(min(gaps), max(gaps), 200)

fig = go.Figure()

fig.add_trace(go.Scatter(
    x=xs,
    y=density(xs),
    mode='lines',
    name='Density'
))

fig.update_layout(
    title="Kernel Density Estimate of Prime Gaps",
    xaxis_title="Prime Gap (Difference Between Consecutive Primes)",
    yaxis_title="Probability Density",
    template="plotly_white"
)

fig.show()

In [11]:
mean_gap = np.mean(gaps)
var_gap = np.var(gaps)
skew_gap = scipy.stats.skew(gaps)

print("Mean:", mean_gap)
print("Variance:", var_gap)
print("Skewness:", skew_gap)

Mean: 13.428887008836247
Variance: 121.60862569703345
Skewness: 1.8391386934249572


In [12]:
sorted_gaps = np.sort(gaps)
cdf = np.arange(len(sorted_gaps)) / len(sorted_gaps)

fig = go.Figure()
fig.add_trace(go.Scatter(x=sorted_gaps, y=cdf, mode='lines'))

fig.update_layout(title="CDF of Prime Gaps")

fig.show()

In [18]:
import plotly.graph_objects as go
import numpy as np
n= 50000
primes_subset = primes[primes <= n]
numbers = np.arange(1, n + 1)
prime_mask = np.isin(numbers, primes_subset)


theta = numbers * 0.15   
r     = np.sqrt(numbers)
x     = r * np.cos(theta)
y     = r * np.sin(theta)

# ── figure ────────────────────────────────────────────────────
fig = go.Figure()

fig.add_trace(go.Scatter(
    x=x, y=y,
    mode="lines",
    line=dict(color="lightgray", width=1),
    name="Spiral",
))

fig.add_trace(go.Scatter(
    x=x[prime_mask], y=y[prime_mask],
    mode="markers",
    marker=dict(size=3, color="red"),
    name="Primes",
))

fig.update_layout(
    title="Prime Numbers on Spiral Curve",
    height=700,
    width=700,
)

fig.show()

In [38]:
import numpy as np
import plotly.graph_objects as go

numbers = np.arange(1, n + 1)
theta = numbers * 0.08
r = np.sqrt(numbers)

x = r * np.cos(theta)
y = r * np.sin(theta)

prime_mask = np.isin(numbers, primes_subset)

step_size = 2000
frames = []
steps = []

for i in range(step_size, n, step_size):
    mask = numbers <= i
    primes_now = mask & prime_mask

    # FRAME (animation)
    frames.append(go.Frame(
        data=[go.Scatter(
            x=x[primes_now],
            y=y[primes_now],
            mode="markers",
            marker=dict(
                size=3,
                color=np.log(numbers[primes_now]),
                colorscale="Inferno",
                showscale=False
            ),
            text=numbers[primes_now],
            hovertemplate="n = %{text}<extra>Prime</extra>"
        )],
        name=str(i)
    ))

    # SLIDER STEP
    steps.append({
        "method": "animate",
        "args": [[str(i)], {"mode": "immediate"}],
        "label": f"n = {i}"
    })

# INITIAL PLOT
init_mask = numbers <= step_size

fig = go.Figure(
    data=[go.Scatter(
        x=x[init_mask & prime_mask],
        y=y[init_mask & prime_mask],
        mode="markers",
        marker=dict(
            size=3,
            color=np.log(numbers[init_mask & prime_mask]),
            colorscale="Inferno"
        ),
        text=numbers[init_mask & prime_mask],
        hovertemplate="n = %{text}<extra>Prime</extra>"
    )],
    frames=frames
)

# LAYOUT
fig.update_layout(
    title="ULAM SPIRAL",
    paper_bgcolor="#000000",
    plot_bgcolor="#000000",
    xaxis=dict(visible=False, scaleanchor="y"),
    yaxis=dict(visible=False),
    height=800,
    width=800,

    # 🎛️ SLIDER
    sliders=[{
        "active": 0,
        "steps": steps,
        "currentvalue": {
            "prefix": "Showing up to: ",
            "font": {"size": 16}
        }
    }],

    # ▶️ PLAY BUTTON
    updatemenus=[{
        "type": "buttons",
        "buttons": [
            {
                "label": "Play",
                "method": "animate",
                "args": [None, {"frame": {"duration": 80, "redraw": True}}]
            },
            {
                "label": "Pause",
                "method": "animate",
                "args": [[None], {"frame": {"duration": 0}}]
            }
        ]
    }]
)

fig.show()

In [39]:
import plotly.graph_objects as go
from math import comb
import numpy as np

# =========================
# FUNCTION: EXACT BINOMIAL MOD n
# =========================
def get_coeffs(n):
    return [comb(n, k) % n for k in range(n+1)]

# =========================
# VALUES TO COMPARE
# =========================
n_values = [17, 18, 19, 20]  # mix of prime + composite

# =========================
# CREATE FIGURE
# =========================
fig = go.Figure()

for n in n_values:
    coeffs = get_coeffs(n)

    # highlight non-zero values
    colors = ["red" if (c != 0 and k not in [0, n]) else "blue"
              for k, c in enumerate(coeffs)]

    fig.add_trace(go.Bar(
        x=list(range(n+1)),
        y=coeffs,
        name=f"n = {n}",
        marker_color=colors,
        visible=(n == n_values[0])  # only first visible initially
    ))

# =========================
# DROPDOWN MENU
# =========================
buttons = []

for i, n in enumerate(n_values):
    visible = [False] * len(n_values)
    visible[i] = True

    buttons.append(dict(
        label=f"n = {n}",
        method="update",
        args=[{"visible": visible},
              {"title": f"AKS Visualization"}]
    ))

fig.update_layout(
    title="AKS Visualization: Binomial Coefficients mod n",
    xaxis_title="k",
    yaxis_title="C(n,k) mod n",

    updatemenus=[dict(
        buttons=buttons,
        direction="down",
        showactive=True
    )]
)

fig.show()

In [22]:
import numpy as np
import plotly.graph_objects as go

bins = np.arange(0, max(primes_subset), 1000)
counts, edges = np.histogram(primes_subset, bins=bins)

fig = go.Figure()

fig.add_trace(go.Bar(
    x=edges[:-1],
    y=counts
))

fig.update_layout(
    title="Prime Density per 1000 Numbers",
    xaxis_title="Number Range",
    yaxis_title="Prime Count"
)

fig.show()

In [23]:
x = primes
pi_x = np.arange(1, len(primes)+1)

fig = go.Figure()

fig.add_trace(go.Scatter(
    x=x,
    y=pi_x,
    mode='lines'
))

fig.update_layout(
    title="Cumulative Prime Count π(x)",
    xaxis_title="Number",
    yaxis_title="Number of Primes"
)

fig.show()

In [ ]:
import numpy as np
import plotly.graph_objects as go

last_digits = primes % 10

digits = [1, 3, 7, 9]
counts = [np.sum(last_digits == d) for d in digits]

fig = go.Figure()

fig.add_trace(go.Bar(
    x=digits,
    y=counts
))

fig.update_layout(
    title="Distribution of Last Digits in Prime Numbers",
    xaxis_title="Last Digit",
    yaxis_title="Count"
)

fig.show()

In [35]:
primes_small = primes[:1000]
gaps_small = gaps[:1000]

In [45]:
from sklearn.linear_model import LinearRegression
import numpy as np
import plotly.graph_objects as go



X = primes_small[1:].reshape(-1, 1)
y = gaps_small[1:]
model = LinearRegression()
model.fit(X, y)

# predictions
y_pred = model.predict(X)

# =========================
# PLOT
# =========================
fig = go.Figure()

# actual data
fig.add_trace(go.Scatter(
    x=primes_small[1:],
    y=y,
    mode='markers',
    name='Actual Gaps',
    marker=dict(size=4, opacity=0.6)
))

# regression line
fig.add_trace(go.Scatter(
    x=primes_small[1:],
    y=y_pred,
    mode='lines',
    name='Regression Line',
    line=dict(color='red', width=3)
))

fig.update_layout(
    title="Linear Regression: Prime vs Gap",
    xaxis_title="Prime Number",
    yaxis_title="Gap"
)

fig.show()

In [46]:
print("Slope:", model.coef_[0])
print("Intercept:", model.intercept_)

Slope: 0.00039415843810125767
Intercept: 6.478828380955014


In [47]:
import pandas as pd
import plotly.express as px

df_corr = pd.DataFrame({
    "prime": primes_small[1:],
    "gap": gaps_small[1:]
})

corr = df_corr.corr()

fig = px.imshow(
    corr,
    text_auto=True,
    title="Correlation Between Prime and Gap"
)

fig.show()

In [48]:
residuals = y - y_pred

fig = go.Figure()

fig.add_trace(go.Scatter(
    x=primes_small[1:],
    y=residuals,
    mode='markers'
))

fig.update_layout(
    title="Residual Plot",
    xaxis_title="Prime",
    yaxis_title="Residual (Actual - Predicted)"
)

fig.show()